# Requirements to collpase requirements tables Note + Making Concordances Concord - Tony Gui

In [2]:
import pandas as pd
from IPython.display import clear_output
import numpy as np
from statsmodels.tsa.api import VAR
import os
from data_cleaning_functions import requirements_clean, concordance_PCE_clean, \
    find_intermediate_industries, concordance_PCQ_clean, get_sales_from_make_matrix, clean_make_matrix, \
    get_demand_shock_from_shaipro_output, get_expenditure_weights_from_shapiro_outputs,plot_shapiro_graph_from_shapiro_ouput,clean_bea_PQE_table, get_final_demand_from_use_table

from pathlib import Path
import matplotlib.pyplot as plt

script_dir = str(Path().resolve().parent)
file_path = os.path.join(script_dir) + "/" 
shapiro_file =  file_path + "Shapiro"
raw_data_path = file_path + "raw_bea_data" 

/opt/anaconda3/envs/BofC_shocks_production/lib/python3.13/site-packages/tqdm/auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm


# Tony's Frankensteined Concordance 🥹

## What I am going to do is extend the BEA PCE to Industry concordance to include the intermediate industries by simply assigning each to an "unassigned" PCE product 

### unassigned is in quotes because technically the PCE to Industry concordance accounts total expenditure but PPI data from BLS isn't even quantity and expenditure so i hope this will do for now 

In [3]:
use_table = pd.read_excel(os.path.join(raw_data_path, "Use_SUT_Framework_2017_DET.xlsx"), sheet_name="2017")
intermediate_industries = find_intermediate_industries(use_table)
intermediate_industries = intermediate_industries.iloc[:, [0]]
intermediate_industries = intermediate_industries.sort_values(by="Industry")
# intermediate_industries

In [4]:
concordance = pd.read_excel(os.path.join(raw_data_path, "PCEBridge_2017_DET.xlsx"), sheet_name="2017")
concordance = concordance_PCE_clean(concordance)
# concordance

In [5]:
bea_quantities = pd.read_excel(os.path.join(raw_data_path, 'BEA Monthly Quantities.xlsx')) # read raw BEA quantities
bea_quantities = clean_bea_PQE_table(bea_quantities, "Quantities", long=True) 
bea_products = bea_quantities[["products"]].drop_duplicates()
# bea_products

In [6]:
# 1) sets
missing_inds = (
    intermediate_industries["Industry"]
    .astype(str).str.strip()
    .dropna().drop_duplicates()
    .sort_values()
    .reset_index(drop=True)
)

used_products = set(
    concordance["PCE Bridge Products"]
    .astype(str).str.strip()
    .dropna().unique()
)

all_products = (
    (bea_products["products"] if isinstance(bea_products, pd.DataFrame) else bea_products)
    .astype(str).str.strip()
    .dropna().drop_duplicates()
)

unused_products = (
    all_products[~all_products.isin(used_products)]
    .sort_values()
    .reset_index(drop=True)
)

# 2) sanity check: need at least 143 unused products for a unique assignment
if len(unused_products) < len(missing_inds):
    raise ValueError(
        f"Not enough unused products: {len(unused_products)} unused vs {len(missing_inds)} industries."
    )

# 3) build the new concordance-style table (143 x 2)
new_concordance_fill = pd.DataFrame({
    "PCE Bridge Products": unused_products.iloc[:len(missing_inds)].to_list(),
    "PCE Bridge Industries": missing_inds.to_list(),
})

# new_concordance_fill

In [ ]:
concordance_stacked = pd.concat([concordance, new_concordance_fill], ignore_index=True)
# concordance_stacked


In [10]:
use_table = pd.read_excel(os.path.join(raw_data_path, 'Use_SUT_Framework_2017_DET.xlsx'), sheet_name='2017')
use_table = use_table.iloc[4:-11]
use_table = use_table.loc[:, use_table.iloc[0].isin(['Commodity Description', 'T001'])]
use_table = use_table.iloc[1:]
use_table.rename(columns={'Unnamed: 1': 'Industry' , 'Unnamed: 405': 'PCE Expenditure'}, inplace=True)
use_table.loc[use_table['Industry'] == 'Drugs and druggists’ sundries', 'Industry'] = 'Drugs and druggists sundries'
use_table.loc[use_table['Industry'] == 'Insurance Carriers, except Direct Life Insurance', 'Industry'] = 'Insurance carriers, except direct life'
use_table.loc[use_table['Industry'] == 'Tobacco product manufacturing', 'Industry'] = 'Tobacco manufacturing'
use_table.loc[use_table['Industry'] == 'Scenic and sightseeing transportation and support activities for transportatio', 'Industry'] = 'scenic and sightseeing transportation and support activities'
use_table.loc[use_table['Industry'] == 'Community food, housing, and other relief services, including rehabilitation services', 'Industry'] = 'community food, housing, and other relief services, including vocational rehabilitation services'
use_table["Industry"] = use_table["Industry"].str.lower()
use_table["Industry"] = use_table["Industry"].str.strip()
use_table = use_table.dropna(subset=['Industry'])
# # use_table = use_table[use_table['PCE Expenditure'].isna()]
# use_table 

In [11]:
use_table

,Industry,Unnamed: 404
5,oilseed farming,40949
6,grain farming,75948
7,vegetable and melon farming,7756
8,fruit and tree nut farming,27330
9,"greenhouse, nursery, and floriculture production",11879
...,...,...
402,other state and local government enterprises,34550
403,scrap,49124
404,used and secondhand goods,33816
405,noncomparable imports,142489


In [12]:
import pandas as pd

# read files
df = pd.read_csv("/Users/tonygui/Desktop/PEQ_Concordance_new.csv")

# filter df to rows where Industry is in bridge["PCE Bridge Industries"]
df_filtered = use_table[use_table["Industry"].isin(df["PCE Bridge Industries"])].copy()

df_filtered

,Industry,Unnamed: 404
21,"iron, gold, silver, and other metal ore mining",13604
25,other support activities for mining,16455
71,ornamental and architectural metal products ma...,56922
72,power boiler and heat exchanger manufacturing,5194
73,metal tank (heavy gauge) manufacturing,4935
81,valve and fittings other than plumbing,40015
83,fabricated pipe and pipe fitting manufacturing,6851
86,farm machinery and equipment manufacturing,6102
88,construction machinery manufacturing,8268
89,mining and oil and gas field machinery manufac...,6364


In [13]:
df_filtered

,Industry,Unnamed: 404
21,"iron, gold, silver, and other metal ore mining",13604
25,other support activities for mining,16455
71,ornamental and architectural metal products ma...,56922
72,power boiler and heat exchanger manufacturing,5194
73,metal tank (heavy gauge) manufacturing,4935
81,valve and fittings other than plumbing,40015
83,fabricated pipe and pipe fitting manufacturing,6851
86,farm machinery and equipment manufacturing,6102
88,construction machinery manufacturing,8268
89,mining and oil and gas field machinery manufac...,6364


# 1. Load in Requirements Matrix 

In [8]:
requirements = pd.read_excel(os.path.join(raw_data_path, 'IxI_TR_2017_PRO_Det.xlsx'), sheet_name='2017')
requirements = requirements_clean(requirements)
requirements

2,oilseed farming,grain farming,vegetable and melon farming,fruit and tree nut farming,"greenhouse, nursery, and floriculture production",other crop farming,dairy cattle and milk production,"beef cattle ranching and farming, including feedlots and dual-purpose ranching and farming",poultry and egg production,"animal production, except cattle and poultry and eggs",...,federal general government (nondefense),postal service,federal electric utilities,other federal government enterprises,state and local government (educational services),state and local government (hospitals and health services),state and local government (other services),state and local government passenger transit,state and local government electric utilities,other state and local government enterprises
nan,,,,,,,,,,,,,,,,,,,,,
oilseed farming,1.279779,0.014409,0.004929,0.001729,0.001137,0.00316,0.023745,0.01215,0.048375,0.006966,...,-0.000636,0.000089,0.000451,0.002027,0.000422,0.0018,0.000539,0.002588,0.000153,0.000357
grain farming,0.002576,1.160693,0.005144,0.004288,0.002814,0.027177,0.103283,0.116055,0.147067,0.023998,...,0.0003,0.000189,0.00128,0.007513,0.001212,0.004625,0.001335,0.006901,0.000319,0.000772
vegetable and melon farming,0.000224,0.000785,1.037335,0.000679,0.000341,0.000616,0.000247,0.000177,0.000243,0.000105,...,0.000006,0.000004,0.00019,0.000907,0.00014,0.000308,0.000098,0.000019,0.000004,0.000009
fruit and tree nut farming,0.000245,0.000826,0.000647,1.026228,0.000361,0.000646,0.000507,0.000257,0.000495,0.000154,...,0.000032,0.000022,0.000933,0.003551,0.000496,0.002885,0.000562,0.000058,0.000017,0.000033
"greenhouse, nursery, and floriculture production",0.000769,0.002365,0.001809,0.001517,1.152284,0.002257,0.000938,0.000594,0.000857,0.000322,...,0.000109,0.000067,0.000186,0.000286,0.000117,0.000714,0.00162,0.001763,0.000117,0.00025
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
state and local government (hospitals and health services),0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,...,0.000051,0.0,0.0,0.000001,0.0,1.000321,0.0,0.0,0.0,0.0
state and local government (other services),0.003345,0.010249,0.007965,0.007278,0.004364,0.008178,0.004048,0.002967,0.003636,0.001896,...,0.001066,0.001097,0.001879,0.002528,0.000768,0.00152,1.003711,0.003982,0.002619,0.002899
state and local government passenger transit,0.00012,0.000219,0.000136,0.000084,0.00011,0.000162,0.000203,0.000135,0.000233,0.000067,...,0.000143,0.000069,0.000191,0.000718,0.002467,0.000231,0.000541,1.008448,0.000119,0.000197


# 2. Calculate Delta

In [9]:
requirements = requirements.T
requirements = requirements.fillna(0)
delta = np.identity(len(requirements)) - np.linalg.inv(requirements)
delta

/var/folders/bs/21p_36y97dqfc1wddk8jv1vw0000gn/T/ipykernel_10302/3131717931.py:2: FutureWarning: Downcasting object dtype arrays on .fillna, .ffill, .bfill is deprecated and will change in a future version. Call result.infer_objects(copy=False) instead. To opt-in to the future behavior, set `pd.set_option('future.no_silent_downcasting', True)`
  requirements = requirements.fillna(0)


array([[2.18230496e-01, 4.40683470e-04, 1.58573724e-04, ...,
        1.26996423e-06, 5.56401465e-04, 1.29145939e-02],
       [8.69983432e-03, 1.34678082e-01, 6.32280326e-04, ...,
        2.99931551e-06, 4.89773260e-04, 2.80987809e-02],
       [2.87985181e-03, 1.56677551e-03, 3.59778733e-02, ...,
        5.46202911e-07, 2.35506830e-03, 2.87196685e-02],
       ...,
       [7.30710756e-08, 8.52456228e-08, 5.12391827e-08, ...,
        8.09158658e-03, 8.42910778e-04, 2.33319882e-03],
       [1.34253220e-10, 3.09135792e-08, 2.01528360e-08, ...,
        9.69786639e-06, 5.65700212e-04, 1.13693450e-02],
       [7.91307821e-09, 4.43092759e-08, 3.36841533e-08, ...,
        1.53823502e-05, 4.58525716e-04, 7.31267212e-03]], shape=(402, 402))

# 2 (Making Concordances Concord) Adding Scrap, Used and secondhand goods and ROW adjustments to Delta

In [10]:
"""These 4 industries are found in the concordance table but not in the Reqirements table so I am 
adding them manually with row and column inputs of zero"""
concordance_but_not_requirments = ["Scrap", "Used and secondhand goods", "Rest of the world adjustment", "noncomparable imports"] 
delta = pd.DataFrame(delta, index=requirements.index, columns=requirements.columns)
delta = delta.reindex(index=requirements.index.append(pd.Index(concordance_but_not_requirments)).str.lower() , columns=requirements.columns.append(pd.Index(concordance_but_not_requirments)).str.lower() , fill_value=0)
delta

,oilseed farming,grain farming,vegetable and melon farming,fruit and tree nut farming,"greenhouse, nursery, and floriculture production",other crop farming,dairy cattle and milk production,"beef cattle ranching and farming, including feedlots and dual-purpose ranching and farming",poultry and egg production,"animal production, except cattle and poultry and eggs",...,state and local government (educational services),state and local government (hospitals and health services),state and local government (other services),state and local government passenger transit,state and local government electric utilities,other state and local government enterprises,scrap,used and secondhand goods,rest of the world adjustment,noncomparable imports
oilseed farming,2.182305e-01,4.406835e-04,1.585737e-04,1.608751e-04,1.585959e-04,4.303772e-03,3.059061e-04,1.258588e-03,5.658938e-04,6.267435e-04,...,0.000001,2.648539e-09,0.001996,1.269964e-06,0.000556,0.012915,0.0,0.0,0.0,0.0
grain farming,8.699834e-03,1.346781e-01,6.322803e-04,6.412868e-04,6.323431e-04,8.904588e-03,1.219444e-03,5.363358e-03,1.138804e-03,3.121992e-03,...,0.000004,6.914341e-09,0.007465,2.999316e-06,0.000490,0.028099,0.0,0.0,0.0,0.0
vegetable and melon farming,2.879852e-03,1.566776e-03,3.597787e-02,5.720080e-04,5.639853e-04,4.426647e-04,1.087635e-03,2.470001e-03,1.015753e-03,1.101832e-03,...,0.000002,1.644074e-08,0.006705,5.462029e-07,0.002355,0.028720,0.0,0.0,0.0,0.0
fruit and tree nut farming,7.340969e-04,1.550789e-03,6.284265e-04,2.553083e-02,5.581646e-04,4.351929e-04,1.076470e-03,3.931517e-03,1.005375e-03,1.872118e-03,...,0.000001,-6.199510e-09,0.006478,1.658714e-07,0.001537,0.020232,0.0,0.0,0.0,0.0
"greenhouse, nursery, and floriculture production",3.650259e-04,7.710037e-04,2.774939e-04,2.815021e-04,1.316849e-01,2.236586e-04,5.352380e-04,1.699724e-03,4.998527e-04,7.544837e-04,...,0.000001,-4.228297e-08,0.003166,2.865100e-07,0.000520,0.004565,0.0,0.0,0.0,0.0
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
other state and local government enterprises,7.913078e-09,4.430928e-08,3.368415e-08,5.390985e-08,1.475397e-08,-2.887312e-09,4.936176e-09,3.347282e-08,3.480128e-09,5.309115e-08,...,0.000009,-8.258717e-09,0.001245,1.538235e-05,0.000459,0.007313,0.0,0.0,0.0,0.0
scrap,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,...,0.000000,0.000000e+00,0.000000,0.000000e+00,0.000000,0.000000,0.0,0.0,0.0,0.0
used and secondhand goods,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,...,0.000000,0.000000e+00,0.000000,0.000000e+00,0.000000,0.000000,0.0,0.0,0.0,0.0
rest of the world adjustment,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,...,0.000000,0.000000e+00,0.000000,0.000000e+00,0.000000,0.000000,0.0,0.0,0.0,0.0


# 2.5b Making Negative Values in Delta Zero

In [11]:
negative_count = (delta < 0).sum().sum()
percent_of_negatives_before = negative_count/402**2
delta[delta < 0] = 0
negative_count_new = (delta < 0).sum().sum()
percent_of_negatives_after = negative_count_new/402**2

# 2.5b Force negatives to be zero but adjust row sums to be same as before

In [12]:
# V = delta.sum(axis=0)
# P = delta[delta > 0].sum()
# delta.loc['norm'] = V/P
# last_values = delta.iloc[-1]
# delta[delta < 0] = 0
# delta = delta.iloc[:-1].div(last_values)
# delta

# Dealting with Intermediate Industries - Making Concordances Concord Section 3.3.1. - Operationalizing Industries without Products

# Step 1. Making Concordances Concord

In [13]:
# use_table = pd.read_excel(os.path.join(raw_data_path, "Use_SUT_Framework_2017_DET.xlsx"), sheet_name="2017")

# # Returns all industries with zero PCE 
# intermediate_industries = find_intermediate_industries(use_table)
# intermediate_industries = intermediate_industries.iloc[:, [0]]
# intermediate_industries = intermediate_industries.sort_values(by="Industry")
# intermediate_industries

# Steps 2 - 5. Making Concordances Concord - Loop over Intermediate Industries and Remove

In [14]:
# # For the Loop 
# big_lambda = np.eye(len(delta)) # create a big_lambda identity matrix that will become out final output
# big_lambda = pd.DataFrame(big_lambda)
# big_lambda = big_lambda.set_index(delta.index)
# big_lambda.columns = delta.index
# delta_industries = delta.index # save all the requirment table industries outside the loop 
# removed = [] # stores all removed industries through the loop 

# i = 0
# for row in intermediate_industries.iloc[::-1].itertuples(): # looping backwards
#     i += 1 
#     current = row.Industry # industry we are currently removing
#     # Create identity matrix for current loop iteration
#     phi_i = np.eye(len(delta) - (i - 1))
#     phi_i = pd.DataFrame(phi_i)
#     phi_i = phi_i.set_index(delta_industries)
#     phi_i.columns = delta_industries

#     current_intermediate_use_table = delta.copy() # use a new intermediates use matrix each time we do this
#     # Remove all the industries we've previously removed in earlier loop iterations 
#     current_intermediate_use_table.drop(columns=removed, inplace=True)
#     current_intermediate_use_table = current_intermediate_use_table.loc[[current]] # the row of the intermediates use table associated with the current industry  
#     current_intermediate_use_table.drop(columns=[current], inplace=True) # drop the column associated with the current industry so we dont include it in our sum
#     current_intermediate_use_table = current_intermediate_use_table.astype(float)
#     current_industry_sum = current_intermediate_use_table.loc[current].sum() # find sum of row

#     # just making sure that we aren't dividing by zero 
#     if current_industry_sum != 0:
#         current_intermediate_use_table = current_intermediate_use_table.astype(float)
#         current_intermediate_use_table.loc[current] = current_intermediate_use_table.loc[current] / current_industry_sum


#     current_intermediate_use_table = current_intermediate_use_table[sorted(current_intermediate_use_table.columns)] # sort the normazlied row alphabetically

#     # remove the current industry from intermediate list
#     intermediate_industries = intermediate_industries[intermediate_industries['Industry'] != current]
#     # drop the current industry column from phi_i and industry indexing
#     phi_i = phi_i.drop(columns=current)
#     delta_industries = delta_industries.drop(current) 
    
#     removed.append(current)

#     # Update phi_i with the current industry sale shares
#     phi_i.loc[current_intermediate_use_table.index] = current_intermediate_use_table.loc[current_intermediate_use_table.index].astype(np.float64).values
#     big_lambda_old = big_lambda
#     big_lambda = big_lambda @ phi_i

# Step 6. Making Concordances Concord - Converting IO matrix from sales shares to dollars

In [15]:
# make_matrix = pd.read_excel(os.path.join(raw_data_path, "Supply_2017_DET.xlsx"), sheet_name="2017")
# sales_vector = get_sales_from_make_matrix(make_matrix) # returns the sales for each industry

# # these industries are not in the make matrix so i will add them manually with zero entries to preserve df sizes
# industries_not_in_make_matrix = ["state and local government passenger transit", "state and local government electric utilities", \
#                       "secondary smelting and alloying of aluminum", "federal electric utilities"]
# not_in_make_matrix = pd.DataFrame({'Industries': industries_not_in_make_matrix, 'Sales': [0,0,0,0]})
# sales_vector = pd.concat([sales_vector, not_in_make_matrix], ignore_index=True)
# sales_vector.set_index('Industries', inplace=True)

# # repeat the sales vector n times to make a sales matrix
# sales_repeated = pd.DataFrame({f'{i}': sales_vector['Sales'].values for i in range(1, len(delta))})
# sales_repeated.set_index(sales_vector.index, inplace=True)
# sales_matrix = pd.concat([sales_vector, sales_repeated], axis=1)
# sales_matrix.columns = delta.columns

# # Y is IO matrix in dollars 
# Y = delta * sales_matrix 

# Step 7. Making Concordances Concord - Value Added for the Economy

In [16]:
# sum_Y = Y.sum(axis=1).to_frame()
# sum_Y.columns = ['Sales']
# VA_pre_transformation = (sales_vector - sum_Y).sum()

# Step 8. Making Concordances Concord - IO Matrix in USD

In [17]:
# # new IO matrix in USD 
# Y_tilde = big_lambda.T @ Y @ big_lambda
# sales_tilde = big_lambda.T @ sales_vector

# # Verifing that economy wide value added is identical to the pre-transformation level
# sum_Y_tilde = Y_tilde.sum(axis=1).to_frame()
# sum_Y_tilde.columns = ['Sales']
# VA_post_transformation = (sales_tilde - sum_Y_tilde).sum()
# # VA_post_transformation

In [18]:
# """Pre transformation and post transformation are not the same"""
# differnece = VA_post_transformation - VA_pre_transformation
# differnece

# Step 9. Making Concordances Concord - Calculating New Delta

In [19]:
# recip_sales = 1/sales_tilde
# sales_tilde_repeated = pd.DataFrame({f'{i}': recip_sales['Sales'].values for i in range(1, len(delta))})
# sales_tilde_repeated.set_index(recip_sales.index, inplace=True)
# sales_tilde_matrix = pd.concat([recip_sales, sales_tilde_repeated], axis=1)
# sales_tilde_matrix.columns = delta.columns

# delta_tilde = Y_tilde * sales_tilde_matrix
# delta = delta_tilde
# # delta

# End of Making Concordances Concord - Back to Requirements to Collapse Requirements Table

# 3. Merge Concordance with Delta

In [20]:
# concordance = pd.read_excel(os.path.join(raw_data_path, "PCEBridge_2017_DET.xlsx"), sheet_name="2017")
# concordance = concordance_PCE_clean(concordance)
# # concordance

concordance = concordance_stacked
concordance

,PCE Bridge Products,PCE Bridge Industries
0,new domestic autos,automobile manufacturing
1,new domestic autos,motor vehicle body manufacturing
2,new foreign autos,automobile manufacturing
3,new light trucks,light truck and utility vehicle manufacturing
4,used autos,scrap
...,...,...
843,outpatient services,valve and fittings other than plumbing
844,outpatient services to households,"veneer, plywood, and engineered wood product m..."
845,"outpatient services, gross output",wholesale electronic markets and agents and br...
846,paramedical services,wiring device manufacturing


In [21]:
"""'federal electric utilities', 'secondary smelting and alloying of aluminum', 'state and local government electric utilities', 'state and local government passenger transit' 
are not an intermediate industry nor do they exist in the PCE concordance so we will simply drop"""
industries_in_requirments = set(delta.columns)
indsutries_in_concordance = set(concordance["PCE Bridge Industries"])
industires_not_in_concordance = industries_in_requirments - indsutries_in_concordance
delta = delta.drop(index=industires_not_in_concordance, columns=industires_not_in_concordance, errors='ignore')
delta


,oilseed farming,grain farming,vegetable and melon farming,fruit and tree nut farming,"greenhouse, nursery, and floriculture production",other crop farming,dairy cattle and milk production,"beef cattle ranching and farming, including feedlots and dual-purpose ranching and farming",poultry and egg production,"animal production, except cattle and poultry and eggs",...,postal service,other federal government enterprises,state and local government (educational services),state and local government (hospitals and health services),state and local government (other services),other state and local government enterprises,scrap,used and secondhand goods,rest of the world adjustment,noncomparable imports
oilseed farming,2.182305e-01,4.406835e-04,1.585737e-04,1.608751e-04,1.585959e-04,0.004304,3.059061e-04,1.258588e-03,5.658938e-04,6.267435e-04,...,2.444614e-05,0.000032,0.000001,2.648539e-09,0.001996,0.012915,0.0,0.0,0.0,0.0
grain farming,8.699834e-03,1.346781e-01,6.322803e-04,6.412868e-04,6.323431e-04,0.008905,1.219444e-03,5.363358e-03,1.138804e-03,3.121992e-03,...,5.113396e-05,0.000047,0.000004,6.914341e-09,0.007465,0.028099,0.0,0.0,0.0,0.0
vegetable and melon farming,2.879852e-03,1.566776e-03,3.597787e-02,5.720080e-04,5.639853e-04,0.000443,1.087635e-03,2.470001e-03,1.015753e-03,1.101832e-03,...,4.708953e-05,0.000078,0.000002,1.644074e-08,0.006705,0.028720,0.0,0.0,0.0,0.0
fruit and tree nut farming,7.340969e-04,1.550789e-03,6.284265e-04,2.553083e-02,5.581646e-04,0.000435,1.076470e-03,3.931517e-03,1.005375e-03,1.872118e-03,...,3.593147e-07,0.000074,0.000001,0.000000e+00,0.006478,0.020232,0.0,0.0,0.0,0.0
"greenhouse, nursery, and floriculture production",3.650259e-04,7.710037e-04,2.774939e-04,2.815021e-04,1.316849e-01,0.000224,5.352380e-04,1.699724e-03,4.998527e-04,7.544837e-04,...,3.902815e-07,0.000076,0.000001,0.000000e+00,0.003166,0.004565,0.0,0.0,0.0,0.0
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
other state and local government enterprises,7.913078e-09,4.430928e-08,3.368415e-08,5.390985e-08,1.475397e-08,0.000000,4.936176e-09,3.347282e-08,3.480128e-09,5.309115e-08,...,3.599164e-04,0.000059,0.000009,0.000000e+00,0.001245,0.007313,0.0,0.0,0.0,0.0
scrap,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,...,0.000000e+00,0.000000,0.000000,0.000000e+00,0.000000,0.000000,0.0,0.0,0.0,0.0
used and secondhand goods,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,...,0.000000e+00,0.000000,0.000000,0.000000e+00,0.000000,0.000000,0.0,0.0,0.0,0.0
rest of the world adjustment,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,...,0.000000e+00,0.000000,0.000000,0.000000e+00,0.000000,0.000000,0.0,0.0,0.0,0.0


In [22]:
in_num_products = concordance['PCE Bridge Industries'].value_counts()

delta_product_columns = pd.DataFrame(index=delta.index, columns=concordance['PCE Bridge Products'])

for column in delta_product_columns: 
    industry = concordance.loc[concordance['PCE Bridge Products'] == column, 'PCE Bridge Industries'].values
    delta_product_columns[column] = delta[industry] / in_num_products[industry]

delta_product_cr = pd.DataFrame(columns=delta_product_columns.columns)
lst_for_industry = []
for row in delta_product_columns.index:
    final_value = delta_product_columns.loc[row] / in_num_products[row]
    products = concordance[concordance['PCE Bridge Industries'] == row]['PCE Bridge Products'].tolist()
    for product in products: 
        lst_for_industry.append(row)
        final_value_row = pd.DataFrame(final_value).T
        final_value_row.index = [product]
        
        delta_product_cr = pd.concat([delta_product_cr, final_value_row])

industry = pd.DataFrame(lst_for_industry, columns=['industry'])
industry.index = delta_product_cr.index
delta_product_cr = pd.concat([delta_product_cr, industry], axis = 1)
delta_product_cr

/var/folders/bs/21p_36y97dqfc1wddk8jv1vw0000gn/T/ipykernel_10302/3732902829.py:19: FutureWarning: The behavior of DataFrame concatenation with empty or all-NA entries is deprecated. In a future version, this will no longer exclude empty or all-NA columns when determining the result dtypes. To retain the old behavior, exclude the relevant entries before the concat operation.
  delta_product_cr = pd.concat([delta_product_cr, final_value_row])


,new domestic autos,new domestic autos,new foreign autos,new light trucks,used autos,used autos,used light trucks,used light trucks,tires,tires,...,other professional medical services,other purchased meals,other recreational services,other services,outpatient services,outpatient services to households,"outpatient services, gross output",paramedical services,pce energy goods and services1,industry
market-based pce other nondurable goods,0.000002,0.000004,0.000002,3.326239e-07,0.0,0.0,0.0,0.0,0.001048,0.0,...,6.042182e-08,0.0,7.405335e-07,2.626054e-09,2.437941e-06,8.410907e-07,0.000419,0.000026,9.379869e-07,oilseed farming
cereals,0.000001,0.000002,0.000001,2.187799e-07,0.0,0.0,0.0,0.0,0.000608,0.0,...,1.596410e-08,0.0,4.420982e-07,8.390552e-09,4.635154e-07,1.653374e-07,0.000107,0.000014,2.720663e-08,grain farming
processed fruits and vegetables,0.000001,0.000002,0.000001,2.187799e-07,0.0,0.0,0.0,0.0,0.000608,0.0,...,1.596410e-08,0.0,4.420982e-07,8.390552e-09,4.635154e-07,1.653374e-07,0.000107,0.000014,2.720663e-08,grain farming
pets and related products,0.000001,0.000002,0.000001,2.187799e-07,0.0,0.0,0.0,0.0,0.000608,0.0,...,1.596410e-08,0.0,4.420982e-07,8.390552e-09,4.635154e-07,1.653374e-07,0.000107,0.000014,2.720663e-08,grain farming
food furnished to employees (including military),0.000001,0.000002,0.000001,2.187799e-07,0.0,0.0,0.0,0.0,0.000608,0.0,...,1.596410e-08,0.0,4.420982e-07,8.390552e-09,4.635154e-07,1.653374e-07,0.000107,0.000014,2.720663e-08,grain farming
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
less: expenditures in the united states by nonresidents,0.000000,0.000000,0.000000,0.000000e+00,0.0,0.0,0.0,0.0,0.000000,0.0,...,0.000000e+00,0.0,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000,0.000000,0.000000e+00,rest of the world adjustment
government employees' expenditures abroad,0.000000,0.000000,0.000000,0.000000e+00,0.0,0.0,0.0,0.0,0.000000,0.0,...,0.000000e+00,0.0,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000,0.000000,0.000000e+00,noncomparable imports
private employees' expenditures abroad,0.000000,0.000000,0.000000,0.000000e+00,0.0,0.0,0.0,0.0,0.000000,0.0,...,0.000000e+00,0.0,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000,0.000000,0.000000e+00,noncomparable imports
u.s. travel outside the united states,0.000000,0.000000,0.000000,0.000000e+00,0.0,0.0,0.0,0.0,0.000000,0.0,...,0.000000e+00,0.0,0.000000e+00,0.000000e+00,0.000000e+00,0.000000e+00,0.000000,0.000000,0.000000e+00,noncomparable imports


# 4. Collapse columns

In [23]:
delta_products = delta_product_cr.T.groupby(delta_product_cr.columns).sum().T
# delta_products

# 5. Make Matrix to Sales

In [24]:
make_matrix = pd.read_excel(os.path.join(raw_data_path, "Supply_2017_DET.xlsx"), sheet_name='2017')
sales = get_sales_from_make_matrix(make_matrix)
# sales

# 6. Merge concordance with sales 

In [25]:
product_sales = pd.merge(concordance, sales, left_on='PCE Bridge Industries', right_on='Industries')
product_sales = product_sales[["PCE Bridge Products", "Industries", 'Sales']]
# product_sales

# 7. Group sum of Sales for every Product

In [26]:
# calculates the number of product categories an Industry belongs to 
product_sales['In#Products'] = product_sales['Industries'].map(product_sales['Industries'].value_counts())
product_sales["Ratio_in_Product"] = product_sales['Sales'] / product_sales['In#Products'] 
product_sales['Sales_Sum'] = product_sales.groupby('PCE Bridge Products')['Ratio_in_Product'].transform('sum')
# product_sales

# 8. Sales Share 

In [27]:
product_sales['Sale Share'] = product_sales["Ratio_in_Product"] / product_sales["Sales_Sum"]
product_sales = product_sales.rename(columns={'Industries': 'industry'})
product_sales = product_sales.rename(columns={'PCE Bridge Products': 'product'})
# product_sales

# 9. Merge Sale shares and Delta

In [28]:
df_reset = delta_products.reset_index()
delta_products = df_reset.rename(columns={'index': 'product'})
delta_products_saleshare = delta_products.merge(product_sales, how = 'inner', on = ['industry', 'product'])
delta_products_saleshare = delta_products_saleshare.drop(columns=['Sales_Sum', "Ratio_in_Product", "In#Products", "Sales", "industry"])
delta_products_saleshare = delta_products_saleshare.set_index(delta_products_saleshare.columns[0])
# delta_products_saleshare

# 10. weightTimesDeltaValue + 11.

In [29]:
# Convert from Wide to Long
delta_final = delta_products_saleshare.reset_index().melt(id_vars=[delta_products_saleshare.index.name, "Sale Share"],
                                var_name="Column Products", value_name="value")

# Just Renaming and Reordering
delta_final = delta_final.rename(columns={delta_products_saleshare.index.name: "Row Products"})
delta_final = delta_final[['Row Products', 'Column Products', 'value', 'Sale Share']]
# Calculating weightTimesDeltaValue
delta_final["weightTimesDeltaValue"] = delta_final["value"] * delta_final["Sale Share"]

# Sum weightTimesDeltaValue grouping by Row Products AND Column Products
delta_final = delta_final.groupby(['Row Products', 'Column Products']).sum()
delta_final
# Convert Back to Wide Format 
delta_final = delta_final.pivot_table(values='weightTimesDeltaValue', index='Row Products', columns='Column Products')

# Removes Index and Column Names cuz it looks better. Both Index and Columns are simply Product Categories now
delta_final.columns.name = None 
delta_final.index.name = None 


labels_to_drop = ["government employees' expenditures abroad", "private employees' expenditures abroad","u.s. travel outside the united states","u.s. student expenditures"]
delta_final = delta_final.drop(index=labels_to_drop, columns=labels_to_drop, errors="ignore")

# delta_final

In [56]:
delta_final

,accessories and parts,accommodations,accounting and other business services,additional aggregates:,admissions to specified spectator amusements,air transportation,alcohol in purchased meals,alcoholic beverages purchased for off-premises consumption,all other professional medical services,"amusement parks, campgrounds, and related recreational services",...,video and audio streaming and rental,"video discs, tapes, and permanent digital downloads",vocational rehabilitation services,watches,water supply and sewage maintenance,water transportation,window coverings,wine,women's and girls' clothing,workers' compensation
accessories and parts,0.147975,1.160988e-06,5.512988e-07,4.512524e-03,0.001408,0.000137,0.000853,2.026378e-04,9.664624e-06,0.000377,...,0.000716,1.579440e-05,0.0,1.005931e-06,0.000274,5.081087e-05,6.365909e-05,1.981058e-08,6.415359e-04,0.000186
accommodations,0.009607,5.534951e-02,1.353841e-07,9.252392e-03,0.002066,0.000207,0.000737,8.433456e-04,8.763091e-06,0.000417,...,0.002157,1.231814e-05,0.0,5.653885e-07,0.000223,2.539946e-05,1.275866e-05,4.163405e-08,1.457018e-05,0.000350
accounting and other business services,0.007321,1.378671e-08,3.167303e-01,1.557281e-02,0.001217,0.000151,0.000431,3.312661e-06,1.372047e-05,0.000508,...,0.003055,1.737185e-06,0.0,3.376280e-04,0.000886,5.733431e-06,1.649341e-05,0.000000e+00,4.071302e-07,0.000077
additional aggregates:,0.005168,7.353138e-08,3.629393e-06,1.084955e-01,0.001485,0.000177,0.001441,0.000000e+00,9.677116e-06,0.000470,...,0.001530,1.131612e-06,0.0,4.795762e-08,0.000771,1.304059e-03,7.503929e-07,0.000000e+00,2.649672e-07,0.000123
admissions to specified spectator amusements,0.005877,3.624838e-08,2.621488e-09,3.045068e-07,0.011271,0.000521,0.003906,9.651599e-05,7.886773e-05,0.001373,...,0.003691,1.834550e-03,0.0,2.778088e-06,0.001150,3.229453e-04,1.258621e-06,0.000000e+00,1.538588e-06,0.001179
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
water transportation,0.002017,7.484579e-06,2.558136e-06,2.432637e-07,0.000224,0.000518,0.000959,5.101139e-06,8.069559e-05,0.006174,...,0.000620,7.096284e-06,0.0,5.024992e-07,0.001111,1.014797e-02,1.225024e-05,3.153519e-05,1.228754e-05,0.000574
window coverings,0.006197,1.862517e-08,2.578668e-08,4.845354e-05,0.000535,0.000061,0.000205,2.050082e-06,4.191658e-06,0.000215,...,0.000766,1.512396e-06,0.0,2.695383e-08,0.000338,2.153228e-03,1.659104e-03,9.252891e-09,3.337499e-03,0.000101
wine,0.010054,1.397710e-08,1.046207e-10,5.348603e-07,0.000733,0.000204,0.000732,3.941448e-07,1.789013e-05,0.000669,...,0.001215,1.668081e-06,0.0,1.851560e-08,0.000382,6.886415e-04,4.122266e-07,6.278299e-02,1.070965e-07,0.000695
women's and girls' clothing,0.000944,8.483426e-09,9.355332e-09,6.906700e-05,0.000603,0.000056,0.000247,8.695080e-06,9.566936e-07,0.000077,...,0.000497,6.281899e-07,0.0,1.949694e-07,0.000126,2.901301e-04,1.676903e-05,0.000000e+00,2.449843e-03,0.000030


# Fixing Products with no price, quantity or expendiuture data 

In [30]:
bea_quantities = pd.read_excel(os.path.join(raw_data_path, 'BEA Monthly Quantities.xlsx')) # read raw BEA quantities
bea_quantities = clean_bea_PQE_table(bea_quantities, "Quantities", long=True) 
bea_quantities = bea_quantities[bea_quantities['products'].isin(delta_final.index)] # drop products taht delta doesnt have
bea_quantities = bea_quantities.drop_duplicates()
bea_quantities['Quantities'] = bea_quantities['Quantities'].replace('---', 0).astype(float)
bea_quantities = bea_quantities.fillna(0)

bea_prices = pd.read_excel(os.path.join(raw_data_path, 'BEA Monthly Prices.xlsx'))
bea_prices = clean_bea_PQE_table(bea_prices, "Prices", long=True)
bea_prices = bea_prices[bea_prices['products'].isin(delta_final.index)]
bea_prices = bea_prices.drop_duplicates()
bea_prices['Prices'] = bea_prices['Prices'].replace('---', 0).astype(float)
bea_prices = bea_prices.fillna(0)

bea_expenditures = pd.read_excel(os.path.join(raw_data_path, 'BEA Monthly Expenditures.xlsx'))
bea_expenditures = clean_bea_PQE_table(bea_expenditures, "Expenditures", long=True)
bea_expenditures = bea_expenditures[bea_expenditures['products'].isin(delta_final.index)]
bea_expenditures = bea_expenditures.drop_duplicates()
bea_expenditures['Expenditures'] = bea_expenditures['Expenditures'].replace('---', 0).astype(float)
bea_expenditures = bea_expenditures.fillna(0)

bea_PQE_merged = pd.merge(left=bea_quantities, right=bea_prices, on=['products', 'date'], how='outer')
bea_PQE_merged = pd.merge(left=bea_PQE_merged, right=bea_expenditures, on=['products', 'date'], how='outer')

# dropping this because 2024-10 has no data yet 
bea_PQE_merged = bea_PQE_merged.dropna(subset=['Expenditures'])

dates = list(set(bea_expenditures["date"]) & set(bea_prices["date"]) & set(bea_quantities["date"]))
dates.sort() # get all BEA data monthly dates

cols_to_check = ['Quantities', 'Prices', 'Expenditures']

# Create filtered DataFrame where at least one value is missing or zero
products_with_zero_somwhere = bea_PQE_merged[
    bea_PQE_merged[cols_to_check].isnull().any(axis=1) |
    (bea_PQE_merged[cols_to_check] == 0).any(axis=1)
]

all_bad_products_dict = {} # For every date products that dont have a value somewhere

for date in dates:
    bad_products_currnet = products_with_zero_somwhere[products_with_zero_somwhere['date'] == date]["products"]
    all_bad_products_dict[date] = bad_products_currnet.tolist()

""""For BEA I will set the entire BEA row to zero if any of the price, quantity or expenditure data is missing"""
zero_mask = (bea_PQE_merged[cols_to_check] == 0).any(axis=1)
# Set all three columns to 0 where the mask is True
bea_PQE_merged.loc[zero_mask, cols_to_check] = 0

bea_prices = bea_PQE_merged[["products", "date", "Prices"]]

/var/folders/bs/21p_36y97dqfc1wddk8jv1vw0000gn/T/ipykernel_10302/1916507575.py:5: FutureWarning: Downcasting behavior in `replace` is deprecated and will be removed in a future version. To retain the old behavior, explicitly call `result.infer_objects(copy=False)`. To opt-in to the future behavior, set `pd.set_option('future.no_silent_downcasting', True)`
  bea_quantities['Quantities'] = bea_quantities['Quantities'].replace('---', 0).astype(float)
/var/folders/bs/21p_36y97dqfc1wddk8jv1vw0000gn/T/ipykernel_10302/1916507575.py:6: FutureWarning: Downcasting object dtype arrays on .fillna, .ffill, .bfill is deprecated and will change in a future version. Call result.infer_objects(copy=False) instead. To opt-in to the future behavior, set `pd.set_option('future.no_silent_downcasting', True)`
  bea_quantities = bea_quantities.fillna(0)
/var/folders/bs/21p_36y97dqfc1wddk8jv1vw0000gn/T/ipykernel_10302/1916507575.py:12: FutureWarning: Downcasting behavior in `replace` is deprecated and will be 

# 12. Calculate Gamma

In [31]:
row_sums = delta_final.sum(axis=1)
gamma = pd.DataFrame(row_sums, columns=['Row_Sum'])
gamma.index = delta_final.index 
gamma = gamma.apply(pd.to_numeric, errors='coerce')
# gamma

# 13. Calculate Omega

In [32]:
delta_gamma = delta_final.merge(gamma, left_on=gamma.index, right_on=delta_final.index)
delta_gamma = delta_gamma.set_index(delta_gamma.columns[0])
row_sums = delta_gamma.iloc[:, -1]
row_sums[row_sums == 0] = np.nan
omega = delta_gamma.iloc[:, :-1].div(row_sums, axis=0)
omega.columns.name = None 
omega.index.name = None 
omega = omega.apply(pd.to_numeric, errors='coerce')
omega

/var/folders/bs/21p_36y97dqfc1wddk8jv1vw0000gn/T/ipykernel_10302/3865145286.py:4: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  row_sums[row_sums == 0] = np.nan


,accessories and parts,accommodations,accounting and other business services,additional aggregates:,admissions to specified spectator amusements,air transportation,alcohol in purchased meals,alcoholic beverages purchased for off-premises consumption,all other professional medical services,"amusement parks, campgrounds, and related recreational services",...,video and audio streaming and rental,"video discs, tapes, and permanent digital downloads",vocational rehabilitation services,watches,water supply and sewage maintenance,water transportation,window coverings,wine,women's and girls' clothing,workers' compensation
accessories and parts,0.231116,1.813297e-06,8.610498e-07,7.047918e-03,0.002198,0.000214,0.001332,3.164913e-04,0.000015,0.000588,...,0.001118,0.000025,0.0,1.571121e-06,0.000428,0.000079,9.942640e-05,3.094129e-08,1.001987e-03,0.000290
accommodations,0.014611,8.417717e-02,2.058961e-07,1.407131e-02,0.003142,0.000315,0.001121,1.282585e-03,0.000013,0.000634,...,0.003281,0.000019,0.0,8.598594e-07,0.000339,0.000039,1.940375e-05,6.331829e-08,2.215876e-05,0.000533
accounting and other business services,0.011783,2.219066e-08,5.097992e-01,2.506551e-02,0.001958,0.000243,0.000693,5.331955e-06,0.000022,0.000818,...,0.004917,0.000003,0.0,5.434355e-04,0.001425,0.000009,2.654728e-05,0.000000e+00,6.553041e-07,0.000124
additional aggregates:,0.008131,1.156925e-07,5.710399e-06,1.707043e-01,0.002337,0.000278,0.002267,0.000000e+00,0.000015,0.000740,...,0.002407,0.000002,0.0,7.545536e-08,0.001213,0.002052,1.180650e-06,0.000000e+00,4.168930e-07,0.000193
admissions to specified spectator amusements,0.016093,9.926415e-08,7.178796e-09,8.338747e-07,0.030865,0.001427,0.010696,2.643036e-04,0.000216,0.003760,...,0.010107,0.005024,0.0,7.607636e-06,0.003150,0.000884,3.446663e-06,0.000000e+00,4.213336e-06,0.003228
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
water transportation,0.011074,4.109554e-05,1.404594e-05,1.335687e-06,0.001228,0.002843,0.005264,2.800880e-05,0.000443,0.033898,...,0.003406,0.000039,0.0,2.759070e-06,0.006102,0.055719,6.726232e-05,1.731501e-04,6.746712e-05,0.003149
window coverings,0.033339,1.001922e-07,1.387169e-07,2.606510e-04,0.002879,0.000330,0.001101,1.102821e-05,0.000023,0.001155,...,0.004120,0.000008,0.0,1.449954e-07,0.001816,0.011583,8.924981e-03,4.977500e-08,1.795374e-02,0.000544
wine,0.016979,2.360531e-08,1.766892e-10,9.033016e-07,0.001237,0.000344,0.001237,6.656535e-07,0.000030,0.001129,...,0.002052,0.000003,0.0,3.127017e-08,0.000645,0.001163,6.961910e-07,1.060314e-01,1.808705e-07,0.001173
women's and girls' clothing,0.009842,8.846416e-08,9.755630e-08,7.202225e-04,0.006287,0.000580,0.002575,9.067127e-05,0.000010,0.000805,...,0.005184,0.000007,0.0,2.033117e-06,0.001317,0.003025,1.748655e-04,0.000000e+00,2.554668e-02,0.000314


# Different gamma and omega for missing products

In [33]:
gamma_omega_monthly = {}  # store a different gamma and omega for each month
delta_final = delta_final.astype("float64", errors="ignore").fillna(0.0)

for date in all_bad_products_dict:
    zero_products = all_bad_products_dict.get(date)  # bad products for current month

    current_gamma = gamma.copy()
    current_delta = delta_final.copy()

    # zero out gamma rows in one shot
    current_gamma.loc[current_gamma.index.isin(zero_products), "Row_Sum"] = 0

    # only keep products that actually exist in both rows and columns of delta
    valid_products = current_delta.index.intersection(zero_products)
    valid_products = valid_products.intersection(current_delta.columns)

    # save diagonal values (i,i) before zeroing rows/cols
    diag_vals = {
        p: current_delta.loc[p, p]
        for p in valid_products
    }

    # zero out bad-product columns
    cols = current_delta.columns.intersection(zero_products)
    current_delta.loc[:, cols] = 0.0

    # zero out bad-product rows
    rows = current_delta.index.intersection(zero_products)
    current_delta.loc[rows, :] = 0.0

    # restore (i,i) entries
    for p in valid_products:
        current_delta.loc[p, p] = diag_vals[p]

    current_row_sum = current_delta.sum(axis=1).astype(float)
    denom = current_row_sum.where(current_row_sum != 0, 1.0)
    current_omega = current_delta.div(denom, axis=0)
    current_omega.loc[current_row_sum == 0, :] = 0.0

    current_omega.columns.name = None
    current_omega.index.name = None

    gamma_omega_monthly[date] = [current_gamma, current_omega]

In [54]:
gamma_omega_monthly.get(pd.Timestamp('1959-01-01 00:00:00'))[0]

,Row_Sum
accessories and parts,0.640263
accommodations,0.657536
accounting and other business services,0.621284
additional aggregates:,0.000000
admissions to specified spectator amusements,0.365171
...,...
water transportation,0.182126
window coverings,0.185894
wine,0.592117
women's and girls' clothing,0.095897


In [55]:
gamma_omega_monthly.get(pd.Timestamp('1959-01-01 00:00:00'))[1]

,accessories and parts,accommodations,accounting and other business services,additional aggregates:,admissions to specified spectator amusements,air transportation,alcohol in purchased meals,alcoholic beverages purchased for off-premises consumption,all other professional medical services,"amusement parks, campgrounds, and related recreational services",...,video and audio streaming and rental,"video discs, tapes, and permanent digital downloads",vocational rehabilitation services,watches,water supply and sewage maintenance,water transportation,window coverings,wine,women's and girls' clothing,workers' compensation
accessories and parts,0.276404,2.168625e-06,1.029778e-06,0.0,0.002629,0.000256,0.001593,3.785098e-04,0.0,0.000704,...,0.0,0.0,0.0,1.878993e-06,0.000512,0.000095,1.189097e-04,3.700444e-08,1.198333e-03,0.000347
accommodations,0.016479,9.493983e-02,2.322214e-07,0.0,0.003544,0.000355,0.001265,1.446573e-03,0.0,0.000715,...,0.0,0.0,0.0,9.697987e-07,0.000382,0.000044,2.188466e-05,7.141400e-08,2.499191e-05,0.000601
accounting and other business services,0.012591,2.371262e-08,5.447641e-01,0.0,0.002092,0.000260,0.000740,5.697650e-06,0.0,0.000874,...,0.0,0.0,0.0,5.807074e-04,0.001523,0.000010,2.836804e-05,0.000000e+00,7.002486e-07,0.000133
additional aggregates:,0.000000,0.000000e+00,0.000000e+00,1.0,0.000000,0.000000,0.000000,0.000000e+00,0.0,0.000000,...,0.0,0.0,0.0,0.000000e+00,0.000000,0.000000,0.000000e+00,0.000000e+00,0.000000e+00,0.000000
admissions to specified spectator amusements,0.018693,1.153060e-07,8.338944e-09,0.0,0.035853,0.001658,0.012425,3.070171e-04,0.0,0.004368,...,0.0,0.0,0.0,8.837088e-06,0.003659,0.001027,4.003670e-06,0.000000e+00,4.894243e-06,0.003750
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
water transportation,0.011731,4.353120e-05,1.487842e-05,0.0,0.001301,0.003011,0.005576,2.966883e-05,0.0,0.035907,...,0.0,0.0,0.0,2.922595e-06,0.006463,0.059022,7.124885e-05,1.834124e-04,7.146578e-05,0.003336
window coverings,0.036497,1.096846e-07,1.518591e-07,0.0,0.003152,0.000362,0.001205,1.207303e-05,0.0,0.001265,...,0.0,0.0,0.0,1.587325e-07,0.001988,0.012680,9.770545e-03,5.449074e-08,1.965470e-02,0.000596
wine,0.017205,2.391835e-08,1.790323e-10,0.0,0.001254,0.000348,0.001253,6.744810e-07,0.0,0.001144,...,0.0,0.0,0.0,3.168485e-08,0.000654,0.001178,7.054235e-07,1.074375e-01,1.832691e-07,0.001189
women's and girls' clothing,0.010728,9.642293e-08,1.063330e-07,0.0,0.006853,0.000632,0.002807,9.882860e-05,0.0,0.000878,...,0.0,0.0,0.0,2.216029e-06,0.001435,0.003298,1.905974e-04,0.000000e+00,2.784501e-02,0.000343


In [ ]:
gamma_omega_monthly.get(pd.Timestamp)

# Start of Doing our Supply/demand contribution graph properly (Which influenceer has hte most influence?)

# Find Sales

In [34]:
# calculate sales in product and time period
sales = pd.DataFrame({'date': pd.Series(dtype='datetime64[ns]'),
                   'products': pd.Series(dtype='str'),
                   'sales': pd.Series(dtype='float')})

for date in dates:

    gamma = gamma_omega_monthly.get(date)[0]
    omega = gamma_omega_monthly.get(date)[1]
 
    # filter expenditures for the current date
    expenditures_date = bea_expenditures[bea_expenditures['date'] == date][['products', 'Expenditures']].set_index('products')
    expenditures_date = expenditures_date.sort_index()
    expenditures_date = expenditures_date.apply(pd.to_numeric, errors='coerce')

    gamma_series = gamma["Row_Sum"]
    diag_matrix = np.diag(gamma_series)

    x = np.identity(len(omega)) - (omega.T @ diag_matrix)

    sales_date = np.linalg.inv(x) @ expenditures_date

    sales_date['date'] = date
    sales_date['products'] = expenditures_date.index
    sales_date.rename(columns={'Expenditures': 'sales'}, inplace=True)

    sales = pd.concat([sales, sales_date], ignore_index=True)

# Find Prices of Intermediates

In [35]:
# # calculate prices of intermediates (we use cobb douglas production with intermediates)
# intermediates = pd.DataFrame({'date': pd.Series(dtype='datetime64[ns]'),
#                    'products': pd.Series(dtype='str'),
#                    'intermediates': pd.Series(dtype='float')})
# for date in dates:

#     prices_date = bea_prices[bea_prices['date'] == date][['products', 'Prices']].set_index('products')
#     prices_date = prices_date.sort_index()

#     gamma = gamma_omega_monthly.get(date)[0]
#     omega = gamma_omega_monthly.get(date)[1]
    
#     for i in gamma.index:
#         log_prices = np.log(prices_date['Prices'])
#         log_prices.replace(-np.inf, 0, inplace=True)        
#         intermediates.loc[len(intermediates)] = [date, i, np.exp(omega.loc[i] @ log_prices)]

rows = []
for d_idx, date in enumerate(dates):

    prices_date = (
        bea_prices.loc[bea_prices["date"] == date, ["products", "Prices"]]
        .set_index("products")
        .sort_index()
    )

    log_prices = np.log(prices_date["Prices"])
    log_prices.replace(-np.inf, 0, inplace=True)

    gamma, omega = gamma_omega_monthly.get(date)

    for i in gamma.index:
        rows.append((
            date,
            i,
            np.exp(omega.loc[i] @ log_prices)
        ))

    # keep VS Code renderer alive
    if d_idx % 1 == 0:
        clear_output(wait=True)

intermediates = pd.DataFrame(
    rows,
    columns=["date", "products", "intermediates"]
)

/opt/anaconda3/envs/BofC_shocks_production/lib/python3.13/site-packages/pandas/core/arraylike.py:399: RuntimeWarning: divide by zero encountered in log
  result = getattr(ufunc, method)(*inputs, **kwargs)


# Find Price of Value Added

In [36]:
# calculate prices of value added
value_added = pd.DataFrame({'date': pd.Series(dtype='datetime64[ns]'),
                   'products': pd.Series(dtype='str'),
                   'value_added': pd.Series(dtype='float')})

for date in dates:
    # filter prices for the current date
    prices_date = bea_prices[bea_prices['date'] == date][['products', 'Prices']].set_index('products')
    prices_date = prices_date.sort_index()

    # filter intermediates for the current date
    intermediates_date = intermediates[intermediates['date'] == date][['products', 'intermediates']].set_index('products')
    intermediates_date = intermediates_date.sort_index()

    gamma = gamma_omega_monthly.get(date)[0]    
    gamma_series = gamma["Row_Sum"]

    value_added_date = np.exp((1/(1 - gamma_series.sort_index()))*(np.log(prices_date['Prices']) - gamma_series.sort_index() * np.log(intermediates_date['intermediates'])))

    value_added_date = value_added_date.reset_index().rename(columns={0: 'value_added'})
    value_added_date['date'] = date
    value_added_date.rename(columns={"index": "products"}, inplace=True)

    value_added = pd.concat([value_added, value_added_date], ignore_index=True)

/opt/anaconda3/envs/BofC_shocks_production/lib/python3.13/site-packages/pandas/core/arraylike.py:399: RuntimeWarning: divide by zero encountered in log
  result = getattr(ufunc, method)(*inputs, **kwargs)
/opt/anaconda3/envs/BofC_shocks_production/lib/python3.13/site-packages/pandas/core/arraylike.py:399: RuntimeWarning: divide by zero encountered in log
  result = getattr(ufunc, method)(*inputs, **kwargs)
/opt/anaconda3/envs/BofC_shocks_production/lib/python3.13/site-packages/pandas/core/arraylike.py:399: RuntimeWarning: divide by zero encountered in log
  result = getattr(ufunc, method)(*inputs, **kwargs)
/opt/anaconda3/envs/BofC_shocks_production/lib/python3.13/site-packages/pandas/core/arraylike.py:399: RuntimeWarning: divide by zero encountered in log
  result = getattr(ufunc, method)(*inputs, **kwargs)
/opt/anaconda3/envs/BofC_shocks_production/lib/python3.13/site-packages/pandas/core/arraylike.py:399: RuntimeWarning: divide by zero encountered in log
  result = getattr(ufunc, me

# Sales and Value Added VAR

In [37]:
lags = 12
residuals_part = []

for product in gamma.index:
    product_bad_dates = products_with_zero_somwhere[products_with_zero_somwhere["products"] == product]
    calculated = pd.merge(left=value_added, right=sales, on=['products', 'date'], how='inner')
    calculated = calculated[calculated['products'] == product][['date', 'value_added', 'sales']].sort_values(['date'])
    calculated = calculated.set_index('date')

    if not product_bad_dates.empty: 
        calculated = calculated[~calculated.index.isin(product_bad_dates['date'])] # remove rows before we have all time series data
    
    calculated['value_added'] = np.log(calculated['value_added']).diff()
    calculated['sales'] = np.log(calculated['sales']).diff()

    calculated.replace([np.inf, -np.inf, np.nan], 0, inplace=True)
    # ensure datetime index (safe even if already datetime)
    calculated.index = pd.to_datetime(calculated.index, errors="coerce")

    # if nothing left (or all dates invalid), skip this product
    if calculated.index.notna().sum() == 0:
        continue

    start = calculated.index.min()
    end = calculated.index.max()

    # guard (extra safe)
    if pd.isna(start) or pd.isna(end):
        continue

    full_index_calc = pd.date_range(start=start, end=end, freq="MS")
    calculated = calculated.reindex(full_index_calc)

    model_calculated = VAR(calculated)
    result_calculated = model_calculated.fit(lags)

    residuals_calculated = result_calculated.resid.reset_index()
    residuals_calculated['products'] = product
    
    residuals_part.append(residuals_calculated)

IO_residuals = pd.concat(residuals_part, ignore_index=True)
IO_residuals.rename(columns={'index': 'date', 'value_added': 'residual_value_added', 'sales': 'residual_sales'}, inplace=True)
IO_residuals = IO_residuals.groupby(['date', 'products']).sum(min_count=1).reset_index()
IO_residuals = IO_residuals.sort_values(['date', 'products'])

# Price and Quantity VAR

In [38]:
lags = 12
residual_temp = []

for product in gamma.index:
    original = bea_PQE_merged[bea_PQE_merged["products"] == product][["date", "Prices", "Quantities"]].sort_values(["date"])
    original = original.set_index("date")

    # force datetime index
    original.index = pd.to_datetime(original.index, errors="coerce")

    # drop rows where date is invalid
    original = original[original.index.notna()]

    # if nothing left, skip
    if original.empty:
        continue

    original = original.dropna()

    # log-diff
    original["Prices"] = np.log(original["Prices"]).diff()
    original["Quantities"] = np.log(original["Quantities"]).diff()

    original = original.replace([np.inf, -np.inf], np.nan).dropna()

    # need enough obs for VAR(lags)
    if len(original) <= lags + 1:
        continue

    start = original.index.min()
    end = original.index.max()
    if pd.isna(start) or pd.isna(end):
        continue

    full_index = pd.date_range(start=start, end=end, freq="MS")
    original = original.reindex(full_index)

    model_original = VAR(original)
    result_original = model_original.fit(lags)

    residuals_original = result_original.resid.reset_index()
    residuals_original['products'] = product
    
    residual_temp.append(residuals_original)
    
residuals_normal = pd.concat(residual_temp, ignore_index=True)
residuals_normal.rename(columns={'index': 'date', 'Prices': 'residual_prices', 'Quantities': 'residual_quantities'}, inplace=True)
residuals_normal = residuals_normal.groupby(['date', 'products']).sum(min_count=1).reset_index()
residuals_normal = residuals_normal.sort_values(['date', 'products'])

/opt/anaconda3/envs/BofC_shocks_production/lib/python3.13/site-packages/pandas/core/arraylike.py:399: RuntimeWarning: divide by zero encountered in log
  result = getattr(ufunc, method)(*inputs, **kwargs)
/opt/anaconda3/envs/BofC_shocks_production/lib/python3.13/site-packages/pandas/core/arraylike.py:399: RuntimeWarning: divide by zero encountered in log
  result = getattr(ufunc, method)(*inputs, **kwargs)
/opt/anaconda3/envs/BofC_shocks_production/lib/python3.13/site-packages/pandas/core/arraylike.py:399: RuntimeWarning: divide by zero encountered in log
  result = getattr(ufunc, method)(*inputs, **kwargs)
/opt/anaconda3/envs/BofC_shocks_production/lib/python3.13/site-packages/pandas/core/arraylike.py:399: RuntimeWarning: divide by zero encountered in log
  result = getattr(ufunc, method)(*inputs, **kwargs)
/opt/anaconda3/envs/BofC_shocks_production/lib/python3.13/site-packages/pandas/core/arraylike.py:399: RuntimeWarning: divide by zero encountered in log
  result = getattr(ufunc, me

# Classification of Price of Value Added and Real Production

In [39]:
residuals_normal['majority_demand'] = ((residuals_normal['residual_prices'] * residuals_normal['residual_quantities']) >= 0).astype(int)
residuals_normal['majority_supply'] = ((residuals_normal['residual_prices'] * residuals_normal['residual_quantities']) < 0).astype(int)

IO_residuals['majority_demand_a'] = ((IO_residuals['residual_value_added'] * IO_residuals['residual_sales']) >= 0).astype(int)
IO_residuals['majority_supply_a'] = ((IO_residuals['residual_value_added'] * IO_residuals['residual_sales']) < 0).astype(int)

# Start of Rethinking Supply and Demand Influence

# 1. Find N X T Value Added Prices and Output Prices

In [40]:
P_VA = value_added.pivot(index='products', columns='date', values='value_added')
P_VA = P_VA.replace([np.inf, -np.inf], 0.0)
log_P_VA = P_VA.applymap(lambda x: np.log(x) if x > 0 else 0)
log_P_VA = log_P_VA.replace([np.inf, -np.inf], 0.0)
log_P_VA = log_P_VA.iloc[:, 12:]

P = bea_prices.pivot(index='products', columns='date', values='Prices')
log_P = P.applymap(lambda x: np.log(x) if x > 0 else 0)
log_P = log_P.iloc[:, 12:]
log_P

/var/folders/bs/21p_36y97dqfc1wddk8jv1vw0000gn/T/ipykernel_10302/3030486278.py:3: FutureWarning: DataFrame.applymap has been deprecated. Use DataFrame.map instead.
  log_P_VA = P_VA.applymap(lambda x: np.log(x) if x > 0 else 0)
/var/folders/bs/21p_36y97dqfc1wddk8jv1vw0000gn/T/ipykernel_10302/3030486278.py:8: FutureWarning: DataFrame.applymap has been deprecated. Use DataFrame.map instead.
  log_P = P.applymap(lambda x: np.log(x) if x > 0 else 0)


date,1960-01-01,1960-02-01,1960-03-01,1960-04-01,1960-05-01,1960-06-01,1960-07-01,1960-08-01,1960-09-01,1960-10-01,...,2023-12-01,2024-01-01,2024-02-01,2024-03-01,2024-04-01,2024-05-01,2024-06-01,2024-07-01,2024-08-01,2024-09-01
products,,,,,,,,,,,,,,,,,,,,,
accessories and parts,3.346460,3.344239,3.341872,3.344133,3.346460,3.346636,3.346636,3.348956,3.349132,3.353861,...,4.834033,4.849723,4.854901,4.844187,4.851546,4.857158,4.852718,4.861725,4.865085,4.868250
accommodations,2.143707,2.142768,2.144761,2.150249,2.155940,2.157675,2.151413,2.145931,2.145229,2.150016,...,4.760472,4.779787,4.781331,4.782303,4.780962,4.780106,4.761216,4.763558,4.780282,4.762012
accounting and other business services,1.629437,1.624524,1.622749,1.627278,1.631199,1.640549,1.641905,1.639385,1.636080,1.637053,...,4.887488,4.907576,4.907332,4.902686,4.922001,4.923828,4.920900,4.929830,4.923398,4.930784
additional aggregates:,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,...,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000
admissions to specified spectator amusements,2.132982,2.138300,2.137003,2.139360,2.140772,2.145229,2.150133,2.157444,2.159177,2.163553,...,4.810647,4.809563,4.821297,4.785072,4.788125,4.790911,4.792546,4.797475,4.789365,4.829601
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
water transportation,3.444512,3.420412,3.435760,3.435760,3.481240,3.458743,3.458743,3.458743,3.458743,3.481240,...,4.599333,4.601574,4.569730,4.589396,4.596029,4.582546,4.617494,4.607956,4.586140,4.574051
window coverings,4.025334,4.035938,4.043490,4.058959,4.069625,4.089633,4.094211,4.098934,4.108790,4.111972,...,4.678820,4.675069,4.675694,4.701716,4.715154,4.681409,4.710737,4.684166,4.725962,4.719106
wine,3.238051,3.243100,3.243100,3.243373,3.245635,3.245751,3.245829,3.245635,3.250336,3.247930,...,4.679387,4.686206,4.691917,4.690430,4.690981,4.691944,4.691100,4.688859,4.690852,4.693099


# 2. Get Big_Theta

In [41]:
# I'm gonna make a different big_theta for every month based on that month's gamma and omega
big_theta_monthly = {} # this will store a different big_theta for each month

for date in dates: 

    gamma = gamma_omega_monthly.get(date)[0]
    omega = gamma_omega_monthly.get(date)[1]

    # first matrix
    step_1 = np.diag(gamma["Row_Sum"]) @ omega
    step_2 = np.eye(len(gamma)) - step_1
    step_3 = np.linalg.inv(step_2)
    # second matrix
    step_4 = np.ones(len(gamma)) - gamma["Row_Sum"]
    step_5 = np.diag(step_4)
    big_theta = step_3 @ step_5
    big_theta = pd.DataFrame(big_theta, index=omega.index, columns=omega.columns)

    big_theta_monthly[date] = big_theta

# 1. Calculate PCE Inflation

In [42]:
bea_expenditures_wide = bea_expenditures.pivot(index='products', columns='date', values='Expenditures')
to_zero = new_concordance_fill["PCE Bridge Products"]
date_cols = [c for c in bea_expenditures_wide.columns if c != "products"]
bea_expenditures_wide.loc[
    bea_expenditures_wide.index.isin(to_zero),
    date_cols
] = 0

Pi = np.log(P.replace(0, np.nan)).diff(axis=1)
Pi = Pi.replace([np.inf, -np.inf], np.nan).fillna(0.0)

bea_expenditures_weights = bea_expenditures_wide.div(bea_expenditures_wide.sum(axis=0), axis=1)
# P_inflation = P / P.shift(axis=1)

PCE_Inflation = bea_expenditures_weights * Pi
PCE_Inflation = PCE_Inflation.fillna(0)

Monthly_Inflation = np.ones((1, PCE_Inflation.shape[0])) @ PCE_Inflation
Monthly_Inflation = Monthly_Inflation.T
Monthly_Inflation

,0
date,
1959-01-01,0.000000
1959-02-01,0.000952
1959-03-01,0.000809
1959-04-01,0.002039
1959-05-01,0.000429
...,...
2024-05-01,-0.000056
2024-06-01,0.001112
2024-07-01,0.001631


# 2. Calculate the Leontief Inverse

In [43]:
from numpy.linalg import inv

B_monthly = {}

for date, obj in gamma_omega_monthly.items():
    omega = obj[1]  # your A_t
    gamma = obj[0]

    gamma_np = gamma.iloc[:, 0].to_numpy(dtype=float)   # length 353
    diag_omega = pd.DataFrame(np.diag(gamma_np), index=omega.index, columns=omega.index)

    A_real = (diag_omega @ omega).T
 
    A_mat = A_real.to_numpy(dtype=float)

    N = A_mat.shape[0]

    # V = diag(row_sums(A))
    v = A_mat.sum(axis=0)
    V = np.diag(v)

    # M = I - A
    M = np.eye(N) - A_mat

    # if a column of M is all zero, set its diagonal entry to 1 
    zero_cols = np.where(np.all(np.abs(M) <= 0, axis=0))[0]
    if zero_cols.size > 0:
        M[zero_cols, zero_cols] = 1.0

    # invert + compute B
    M_inv = inv(M)
    B_mat = V @ M_inv

    B_monthly[date] = pd.DataFrame(B_mat, index=A_real.index, columns=A_real.columns)

In [44]:
gamma_np

array([0.64026347, 0.65753593, 0.62128441, 0.        , 0.36517096,
       0.06568902, 0.15722297, 0.32018014, 0.1054211 , 0.15050787,
       0.12387909, 0.24901695, 0.55304711, 0.55653354, 0.14645762,
       0.29033412, 0.13896391, 0.54477512, 0.25951426, 0.11317353,
       0.23763363, 0.27123548, 0.11452241, 0.44442955, 0.25942196,
       0.29357944, 0.14663959, 0.24864628, 0.35852228, 0.78010533,
       0.42701655, 0.64591007, 0.25925354, 0.17181488, 0.11065268,
       0.24517229, 0.05153323, 0.109899  , 0.504415  , 0.1850062 ,
       0.32718779, 0.40625771, 0.16067944, 0.20344699, 0.14663959,
       0.23456209, 0.27015038, 0.18792296, 0.19766888, 0.43497299,
       0.        , 0.44229457, 0.49685921, 0.51687475, 0.19644327,
       0.3735849 , 0.11768382, 0.31734452, 0.31989979, 0.09642282,
       0.04611788, 0.66388524, 0.35352752, 0.05189658, 0.34443573,
       0.50802091, 0.25053014, 0.13664251, 0.22926417, 0.31802267,
       0.6237862 , 0.82081885, 0.50179784, 0.1631912 , 0.09102

In [45]:
bea_expenditures_weights

date,1959-01-01,1959-02-01,1959-03-01,1959-04-01,1959-05-01,1959-06-01,1959-07-01,1959-08-01,1959-09-01,1959-10-01,...,2023-12-01,2024-01-01,2024-02-01,2024-03-01,2024-04-01,2024-05-01,2024-06-01,2024-07-01,2024-08-01,2024-09-01
products,,,,,,,,,,,,,,,,,,,,,
accessories and parts,0.002832,0.002843,0.002812,0.002854,0.002837,0.002855,0.002885,0.002946,0.002913,0.002908,...,0.003673,0.003649,0.003630,0.003654,0.003633,0.003630,0.003591,0.003613,0.003609,0.003606
accommodations,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,...,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000
accounting and other business services,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,...,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000
additional aggregates:,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,...,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000
admissions to specified spectator amusements,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,...,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
water transportation,0.000003,0.000003,0.000003,0.000003,0.000003,0.000003,0.000003,0.000003,0.000003,0.000003,...,0.000338,0.000330,0.000323,0.000320,0.000334,0.000341,0.000343,0.000350,0.000357,0.000362
window coverings,0.002773,0.002758,0.002725,0.002666,0.002787,0.002822,0.002717,0.002690,0.002719,0.002716,...,0.001611,0.001589,0.001566,0.001585,0.001557,0.001549,0.001558,0.001555,0.001539,0.001536
wine,0.001865,0.001829,0.001802,0.001762,0.001804,0.001819,0.001818,0.001801,0.001789,0.001797,...,0.003611,0.003560,0.003559,0.003559,0.003544,0.003532,0.003562,0.003549,0.003535,0.003541


# 3. Calculate PCE to VA Shares: Omega

In [46]:
bea_expenditures_weights.columns = pd.to_datetime(bea_expenditures_weights.columns)
months = sorted([ts for ts in B_monthly.keys() if ts in bea_expenditures_weights.columns])

Omega = pd.DataFrame(index=bea_expenditures_weights.index, columns=months, dtype=float)

for ts in months:
    B = B_monthly[ts]                      # NxN dataframe
    w = bea_expenditures_weights[ts]       # length-N Series

    Omega.loc[:, ts] = B.to_numpy() @ bea_expenditures_weights[ts].to_numpy(dtype=float)

In [47]:
Omega

,1959-01-01,1959-02-01,1959-03-01,1959-04-01,1959-05-01,1959-06-01,1959-07-01,1959-08-01,1959-09-01,1959-10-01,...,2023-12-01,2024-01-01,2024-02-01,2024-03-01,2024-04-01,2024-05-01,2024-06-01,2024-07-01,2024-08-01,2024-09-01
products,,,,,,,,,,,,,,,,,,,,,
accessories and parts,0.013580,0.014036,0.014258,0.014373,0.014210,0.014151,0.014463,0.014769,0.014669,0.013905,...,0.010290,0.009909,0.010036,0.010033,0.010084,0.010132,0.009815,0.010098,0.009880,0.009991
accommodations,0.000012,0.000012,0.000012,0.000012,0.000012,0.000012,0.000012,0.000012,0.000012,0.000012,...,0.000015,0.000014,0.000015,0.000014,0.000015,0.000015,0.000014,0.000015,0.000014,0.000014
accounting and other business services,0.000027,0.000028,0.000028,0.000028,0.000027,0.000027,0.000027,0.000027,0.000027,0.000026,...,0.000019,0.000018,0.000018,0.000018,0.000018,0.000018,0.000018,0.000018,0.000018,0.000018
additional aggregates:,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,...,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000,0.000000
admissions to specified spectator amusements,0.000771,0.000770,0.000769,0.000768,0.000767,0.000769,0.000771,0.000774,0.000771,0.000770,...,0.000679,0.000683,0.000682,0.000682,0.000685,0.000687,0.000688,0.000687,0.000686,0.000688
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
water transportation,0.000171,0.000170,0.000170,0.000170,0.000170,0.000170,0.000171,0.000171,0.000170,0.000171,...,0.000202,0.000201,0.000200,0.000199,0.000202,0.000204,0.000204,0.000205,0.000206,0.000208
window coverings,0.000527,0.000524,0.000518,0.000507,0.000529,0.000536,0.000516,0.000511,0.000517,0.000516,...,0.000308,0.000304,0.000300,0.000303,0.000298,0.000296,0.000298,0.000297,0.000294,0.000294
wine,0.001214,0.001191,0.001174,0.001148,0.001175,0.001185,0.001184,0.001173,0.001166,0.001171,...,0.002353,0.002320,0.002320,0.002319,0.002310,0.002302,0.002321,0.002313,0.002304,0.002308


In [48]:
# import numpy as np
# import pandas as pd

# Pi = np.log(P.replace(0, np.nan)).diff(axis=1)
# Pi = Pi.replace([np.inf, -np.inf], np.nan).fillna(0.0)

# pi_va_cols = {}

# for date, obj in gamma_omega_monthly.items():
#     omega_t = obj[1]                 # NxN
#     gamma_t = 1 - obj[0]             # denom vector-like

#     # pi_t is indexed by product j (must align to omega_t.columns)
#     pi_t = Pi[date].astype(float).reindex(omega_t.columns)

#     # post_sum[i] = sum_j omega[i,j] * pi_j   (ROW-based)
#     post_sum = omega_t @ pi_t                # indexed by omega_t.index (i)

#     numerator = pi_t.reindex(omega_t.index) - post_sum

#     gamma_t = gamma_t.squeeze().reindex(numerator.index).astype(float)
#     pi_va_cols[date] = numerator / gamma_t.replace(0, np.nan)

# PI_VA = pd.DataFrame(pi_va_cols)

# Get PI_VA

In [49]:
import numpy as np
import pandas as pd

Pi = np.log(P.replace(0, np.nan)).diff(axis=1)
Pi = Pi.replace([np.inf, -np.inf], np.nan).fillna(0.0)

pi_va_cols = {}

for date, obj in gamma_omega_monthly.items():
    omega_t = obj[1]                 # NxN
    gamma_t = obj[0]             # denom vector-like

    # pi_t indexed by product j (must align to omega_t.index because j is rows now)
    pi_t = Pi[date].astype(float).reindex(omega_t.index)

    # post_sum[i] = sum_j omega[j,i] * pi_j   (COLUMN-based)
    post_sum = omega_t.T @ pi_t              # indexed by omega_t.columns (i)

    # numerator[i] = pi_i - post_sum[i]
    numerator = Pi[date].astype(float).reindex(omega_t.columns) - post_sum

    gamma_t = gamma_t.squeeze().reindex(numerator.index).astype(float)
    pi_va_cols[date] = numerator / gamma_t.replace(0, np.nan)

PI_VA = pd.DataFrame(pi_va_cols)

In [50]:
PI_PCE_APPROX = (Omega * PI_VA).sum(axis=0)   
PI_PCE_APPROX

1959-01-01    0.000000
1959-02-01    0.001899
1959-03-01   -0.000242
1959-04-01    0.000555
1959-05-01    0.001738
                ...   
2024-05-01    0.001819
2024-06-01   -0.002895
2024-07-01   -0.003811
2024-08-01   -0.001628
2024-09-01   -0.001831
Length: 789, dtype: float64

In [51]:
Monthly_Inflation

,0
date,
1959-01-01,0.000000
1959-02-01,0.000952
1959-03-01,0.000809
1959-04-01,0.002039
1959-05-01,0.000429
...,...
2024-05-01,-0.000056
2024-06-01,0.001112
2024-07-01,0.001631
